# Seattle Lidar

## Visualize Lidar Scattered Point Elevation Data

This notebook uses hvPlot and Datashader to visualize Lidar elevation data from [the Puget Sound Lidar consortium](https://pugetsoundlidar.ess.washington.edu/), a source of Lidar data for the Puget Sound region of the state of Washington, U.S.A.

### Lidar Elevation Data

Example X,Y,Z scattered point elevation data from the unpacked 7zip files (unpacked as .gnd files)

```
! head ../data/q47122d2101.gnd
```
```
X,Y,Z
1291149.60,181033.64,467.95
1291113.29,181032.53,460.24
1291065.38,181035.74,451.41
1291113.16,181037.32,455.51
1291116.68,181037.42,456.20
1291162.42,181038.90,467.81
1291111.90,181038.15,454.89
1291066.62,181036.73,451.41
1291019.10,181035.20,451.64
```

The Seattle area example below loads 25 `.gnd` elevation files like the one above. We'll download, cache and read the data using `intake`.

**NOTE**: Downloading the data for the first time takes about 2 mins due to its large size.

In [1]:
import intake

cat = intake.open_catalog('./catalog.yml')
list(cat)

['seattle_lidar']

In [2]:
lidar = cat.seattle_lidar()
ddf_original = lidar.to_dask()
print(len(ddf_original))
ddf_original.head(2)

94507551


,X,Y,Z
0,1293274.13,181399.80,435.79
1,1293278.38,181393.05,434.58


### Geographic Metadata

Since the data are geographic, we need to know the coordinate reference system (CRS) of the X and Y. All the geographic metadata is stored in the data source entry in the intake catalog.

In [3]:
lidar.metadata['crs']

'State Plane Coordinate System Washington North FIPS 4601'

We intend to display the data overlayed on top of a web basemap (aka tiled web map) which usually uses the Web Mercator (EPSG:3857) projection. We convert the data now to this projection so we only have to do it once. Note that we could have installed [GeoViews](https://geoviews.org/) and called hvPlot with `geo=True` to enable on-the-fly projection of the data to the right system. However, since we are going to generate many plots in this notebook, it is worth pre-processing the data beforehand not to pay the projection cost on every new plot.

In [4]:
from pyproj.transformer import Transformer

# Washington State Plane North EPSG code and Mercator projection EPSG code
transformer = Transformer.from_crs('epsg:2855','epsg:3857')

In [5]:
FT_2_M = 0.3048 # conversion factor from feet to meters

def convert_coords(df):
    lon, lat = transformer.transform(df.X.values * FT_2_M, df.Y.values * FT_2_M)
    df['meterswest'], df['metersnorth'] = lon, lat
    return df[['meterswest', 'metersnorth', 'Z']]

Try out the convert_coords function on a subset of the data

In [6]:
convert_coords(ddf_original.head(2))

,meterswest,metersnorth,Z
0,-1.360741e+07,6.022197e+06,435.79
1,-1.360741e+07,6.022194e+06,434.58


### Convert the coordinates

Since our real dataset is large and partitioned using dask, we need to think about how to apply the `convert_coords` function to our data. 

In [7]:
import dask
import dask.distributed
import dask.delayed
from dask.config import set

set({'distributed.worker.memory.target': 0.8,
     'distributed.worker.memory.spill': 0.9,
     'distributed.worker.memory.pause': 0.95,
     'distributed.worker.memory.terminate': 0.98})

In [8]:
dask.distributed.Client(memory_limit='12GB')

Connection method: Cluster object,Cluster type: distributed.LocalCluster
Dashboard: http://127.0.0.1:8787/status,
Dashboard: http://127.0.0.1:8787/status,Workers: 4
Total threads: 4,Total memory: 44.70 GiB
Status: running,Using processes: True
Comm: tcp://127.0.0.1:39895,Workers: 4
Dashboard: http://127.0.0.1:8787/status,Total threads: 4
Started: Just now,Total memory: 44.70 GiB
Comm: tcp://127.0.0.1:33495,Total threads: 1
Dashboard: http://127.0.0.1:33447/status,Memory: 11.18 GiB
Nanny: tcp://127.0.0.1:41671,


Explore the task graph to figure out a performant way to split up the coords conversion. First we'll try with using `dask.delayed`.

In [9]:
dask.delayed(convert_coords)(ddf_original).visualize(engine='cytoscape')

CytoscapeWidget(cytoscape_layout={'name': 'dagre', 'rankDir': 'BT', 'nodeSep': 10, 'edgeSep': 10, 'spacingFact…

We can see that even though we thought `dask.delayed` would help, in actuality we would be requiring all the processes to be done first and then the conversion would happen on the whole dataset in one go. Another approach would be to use `dask.map_partitions` to do the conversion on each piece of the data.

In [10]:
ddf = ddf_original.map_partitions(convert_coords)
ddf.visualize(engine='cytoscape', tasks=True)

CytoscapeWidget(cytoscape_layout={'name': 'dagre', 'rankDir': 'BT', 'nodeSep': 10, 'edgeSep': 10, 'spacingFact…

Now that we have set up the task graph, we can use `ddf` directly to do the computations on the fly. However, since this dataset fits in memory (~8 GB), we will do the computation and keep the output in memory for quick use when plotting.

**NOTE:** This next cell takes about a minute to run.

In [11]:
%%time
df = ddf.compute()

CPU times: user 1.68 s, sys: 2.04 s, total: 3.72 s
Wall time: 44.5 s


In [12]:
df.info()

<class 'pandas.core.frame.DataFrame'>
Index: 94507551 entries, 0 to 3822295
Data columns (total 3 columns):
 #   Column       Dtype  
---  ------       -----  
 0   meterswest   float64
 1   metersnorth  float64
 2   Z            float64
dtypes: float64(3)
memory usage: 2.8 GB


If all the data doesn't fit in memory on your machine, try downsampling the data from each file to only keep 1/100th of the total data. To avoid unnecessary computation, it is better to do the downsampling first and _then_ convert the coordinates.

In [13]:
ddf_small = ddf_original.sample(frac=0.01).map_partitions(convert_coords)
ddf_small.visualize(engine='cytoscape', tasks=True)

CytoscapeWidget(cytoscape_layout={'name': 'dagre', 'rankDir': 'BT', 'nodeSep': 10, 'edgeSep': 10, 'spacingFact…

In [14]:
%%time
df_small = ddf_small.compute()

CPU times: user 587 ms, sys: 116 ms, total: 704 ms
Wall time: 14.8 s


### Plot

In [15]:
import hvplot.dask # noqa
import hvplot.pandas # noqa

To simplify the exploration of the time required to display different data, define a function that accepts a regular `pandas` dataframe or a `dask` delayed dataframe. 

In [16]:
def plot(data, **kwargs):
    """Plot point elevation data, rasterizing by mean elevation"""
    options = dict(cmap='blues_r', width=800, height=800, xaxis=None, yaxis=None, tiles='ESRI')
    options |= kwargs
    return data.hvplot.points('meterswest', 'metersnorth', color='Z', rasterize=True,
                              aggregator='mean', **options)

Then we will construct the plot using the `df_small` dataset. 

### Benchmarking

Here, we measure the execution time of the `display` function from IPython. Without including `display`, the timing would only reflect the rapid creation of the HoloViews `DynamicMap` objects. By including `display`, we also capture the duration of various internal Python operations required to render the plot on the screen, such as the rasterization process.

In [17]:
from IPython.display import display

In [18]:
%%time

display(plot(df_small))

:DynamicMap   []
   :Overlay
      .Tiles.I :Tiles   [x,y]
      .Image.I :Image   [meterswest,metersnorth]   (meterswest_metersnorth Z)

CPU times: user 1.4 s, sys: 270 ms, total: 1.67 s
Wall time: 1.86 s


In [19]:
%%time

display(plot(df))

:DynamicMap   []
   :Overlay
      .Tiles.I :Tiles   [x,y]
      .Image.I :Image   [meterswest,metersnorth]   (meterswest_metersnorth Z)

CPU times: user 3.03 s, sys: 164 ms, total: 3.19 s
Wall time: 3.07 s


In [20]:
%%time

display(plot(ddf))

:DynamicMap   []
   :Overlay
      .Tiles.I :Tiles   [x,y]
      .Image.I :Image   [meterswest,metersnorth]   (meterswest_metersnorth Z)

CPU times: user 8.45 s, sys: 1.04 s, total: 9.49 s
Wall time: 2min 27s


## Visualize Raster of Point Data

If we compute a raster of the point data then we don't need to store as much data in memory, which should allow faster interactions, and allow use with lots of other tools.

In [21]:
%%time
raster = plot(df, dynamic=False, width=1000, height=1000, tiles=None).data

CPU times: user 2.05 s, sys: 125 ms, total: 2.17 s
Wall time: 2.09 s


The result is an `xarray.Dataset` with x and y coordinates and a 2D array of Z values.

In [22]:
raster.metersnorth[1] - raster.metersnorth[0]

<xarray.DataArray 'metersnorth' ()> Size: 8B
array(10.29223724)

With these data we can use the geo tools found in the `xarray-spatial` library to compute and visualize the elevation using hillshading for instance. See [Datashader User Guide](https://datashader.org/user_guide/Geography.html) for more datashader and `xarray-spatial` geo tooling.

In [23]:
from xrspatial import hillshade
import hvplot.xarray # noqa

In [24]:
illuminated = hillshade(raster.get('meterswest_metersnorth Z'))
illuminated.hvplot.image(
    'meterswest', 'metersnorth', data_aspect=1, cmap='blues', tiles='ESRI',
    width=600, height=600, padding=0, xlabel='Longitude', ylabel='Latitude', colorbar=False,
)

:Overlay
   .Tiles.I :Tiles   [x,y]
   .Image.I :Image   [meterswest,metersnorth]   (hillshade)

## Ideas for future work

It'd be nice to have a `rasterio` writer from `xarray` so that we could easily write chunked geotiffs from `xarray` objects.

Something like:

```python
raster.to_rasterio(path=None, mode='w', compute=True)
```